In [1]:
import os
import cv2
import numpy as np
import random
import matplotlib.pyplot as plt

from keras.models import Sequential
from keras import layers, Model
from sklearn.model_selection import train_test_split
from keras.layers import Conv2D, PReLU,BatchNormalization, Flatten
from keras.layers import UpSampling2D, LeakyReLU, Dense, Input, add
from tqdm import tqdm
from keras.models import load_model
from numpy.random import randint
from keras.preprocessing.image import ImageDataGenerator

In [2]:
import tensorflow_hub as hub
import tensorflow as tf

# GENERATOR NETWORK

In [3]:
def res_block(ip):
    
    res_model = Conv2D(64, (3,3), padding = "same")(ip)
    res_model = BatchNormalization(momentum = 0.5)(res_model)
    res_model = PReLU(shared_axes = [1,2])(res_model)
    
    res_model = Conv2D(64, (3,3), padding = "same")(res_model)
    res_model = BatchNormalization(momentum = 0.5)(res_model)
    
    return add([ip,res_model])

def upscale_block(ip):
    
    up_model = Conv2D(256, (3,3), padding="same")(ip)
    up_model = UpSampling2D( size = 2 )(up_model)
    up_model = PReLU(shared_axes=[1,2])(up_model)
    
    return up_model

#Generator model
def create_gen(gen_ip, num_res_block):
    
    layers = Conv2D(64, (9,9), padding="same")(gen_ip)
    layers = PReLU(shared_axes=[1,2])(layers)

    temp = layers

    for i in range(num_res_block):
        layers = res_block(layers)

    layers = Conv2D(64, (3,3), padding="same")(layers)
    layers = BatchNormalization(momentum=0.5)(layers)
    layers = add([layers,temp])

    layers = upscale_block(layers)
    layers = upscale_block(layers)

    op = Conv2D(3, (9,9), padding="same")(layers)

    return Model(inputs=gen_ip, outputs=op)


# DISCRIMINATOR NETWORK

In [4]:
def discriminator_block(ip, filters, strides=1, bn=True):
    
    disc_model = Conv2D(filters, (3,3), strides = strides, padding="same")(ip)
    
    if bn:
        disc_model = BatchNormalization( momentum=0.8 )(disc_model)
    
    disc_model = LeakyReLU( alpha=0.2 )(disc_model)
    
    return disc_model


#Discriminator model
def create_disc(disc_ip):

    df = 64
    
    d1 = discriminator_block(disc_ip, df, bn=False)
    d2 = discriminator_block(d1, df, strides=2)
    d3 = discriminator_block(d2, df*2)
    d4 = discriminator_block(d3, df*2, strides=2)
    d5 = discriminator_block(d4, df*4)
    d6 = discriminator_block(d5, df*4, strides=2)
    d7 = discriminator_block(d6, df*8)
    d8 = discriminator_block(d7, df*8, strides=2)
    
    d8_5 = Flatten()(d8)
    d9 = Dense(df*16)(d8_5)
    d10 = LeakyReLU(alpha=0.2)(d9)
    validity = Dense(1, activation='sigmoid')(d10)

    return Model(disc_ip, validity)


# VGG19 NETWORK

In [5]:
from keras.applications import VGG19

def build_vgg(hr_shape):
    
    vgg = VGG19(weights="imagenet",include_top=False, input_shape=hr_shape)
    
    return Model(inputs=vgg.inputs, outputs=vgg.layers[10].output)


# GAN MODEL

In [6]:
#Combined model
def create_comb(gen_model, disc_model, vgg, lr_ip, hr_ip):
    gen_img = gen_model(lr_ip)
    
    gen_features = vgg(gen_img)
    
    disc_model.trainable = False
    validity = disc_model(gen_img)
    
    return Model(inputs=[lr_ip, hr_ip], outputs=[validity, gen_features])

# LOAD DATA

In [7]:
# # Total number of images =n=5000
# n=10
# lr_list = os.listdir("/kaggle/input/tenk-imgs/lr_10k/lr_10k")[:n]

# lr_images = []
# for img in lr_list:
#     img_lr = cv2.imread("/kaggle/input/tenk-imgs/lr_10k/lr_10k/" + img)
#     img_lr = cv2.cvtColor(img_lr, cv2.COLOR_BGR2RGB)
#     lr_images.append(img_lr)   

# hr_list = os.listdir("/kaggle/input/tenk-imgs/hr_10k/hr_10k")[:n]
    
# hr_images = []
# for img in hr_list:
#     img_hr = cv2.imread("/kaggle/input/tenk-imgs/hr_10k/hr_10k/" + img)
#     img_hr = cv2.cvtColor(img_hr, cv2.COLOR_BGR2RGB)
#     hr_images.append(img_hr)   

# lr_images = np.array(lr_images)
# hr_images = np.array(hr_images)


# DATA VISUALIZATION AND SCALING

In [8]:
# image_number = random.randint(0, len(lr_images)-1)
# plt.figure(figsize=(12, 6))
# plt.subplot(121)
# plt.imshow(np.reshape(lr_images[image_number], (32, 32, 3)))
# plt.subplot(122)
# plt.imshow(np.reshape(hr_images[image_number], (128, 128, 3)))
# plt.show()

# lr_images = lr_images / 255.
# hr_images = hr_images / 255.

# SPLITING DATA

In [9]:

# lr_train, lr_test, hr_train, hr_test = train_test_split(lr_images, hr_images, 
#                                                       test_size=0.33, random_state=42)



# hr_shape = (hr_train.shape[1], hr_train.shape[2], hr_train.shape[3])
# lr_shape = (lr_train.shape[1], lr_train.shape[2], lr_train.shape[3])

lr_ip = Input(shape=(32,32,3))
hr_ip = Input(shape=(128,128,3))

print(lr_ip)
print(hr_ip)

KerasTensor(type_spec=TensorSpec(shape=(None, 32, 32, 3), dtype=tf.float32, name='input_1'), name='input_1', description="created by layer 'input_1'")
KerasTensor(type_spec=TensorSpec(shape=(None, 128, 128, 3), dtype=tf.float32, name='input_2'), name='input_2', description="created by layer 'input_2'")


# MODEL BUILDING

In [10]:
# Load the ESRGAN model from TensorFlow Hub
esrgan_model = hub.KerasLayer("https://tfhub.dev/captain-pool/esrgan-tf2/1", trainable=True)

# Create your retraining model
generator = tf.keras.Sequential([
    esrgan_model,
    tf.keras.layers.Conv2D(filters=3, kernel_size=[1, 1], strides=[1, 1])
])
# generator.summary()

discriminator = create_disc(hr_ip)
discriminator.compile(loss="binary_crossentropy", optimizer="adam", metrics=['accuracy'])
discriminator.summary()

vgg = build_vgg((128,128,3))
print(vgg.summary())
vgg.trainable = False

gan_model = create_comb(generator, discriminator, vgg, lr_ip, hr_ip)

gan_model.compile(loss=["binary_crossentropy", "mse"], loss_weights=[1e-3, 1], optimizer="adam")
gan_model.summary()

Model: "model"
_________________________________________________________________
 Layer (type)                Output Shape              Param #   
 input_2 (InputLayer)        [(None, 128, 128, 3)]     0         
                                                                 
 conv2d_1 (Conv2D)           (None, 128, 128, 64)      1792      
                                                                 
 leaky_re_lu (LeakyReLU)     (None, 128, 128, 64)      0         
                                                                 
 conv2d_2 (Conv2D)           (None, 64, 64, 64)        36928     
                                                                 
 batch_normalization (BatchN  (None, 64, 64, 64)       256       
 ormalization)                                                   
                                                                 
 leaky_re_lu_1 (LeakyReLU)   (None, 64, 64, 64)        0         
                                                             

# MODEL TRAINING

In [11]:
# Data Generator
lr_datagen = ImageDataGenerator(rescale=1.0/255)  
hr_datagen = ImageDataGenerator(rescale=1.0/255)  

lr_generator = lr_datagen.flow_from_directory("/kaggle/input/flickr-faces-15000/flickr_faces_15000_original", class_mode='binary',  target_size=(32,32), batch_size=1, shuffle=False)
hr_generator = hr_datagen.flow_from_directory("/kaggle/input/flickr-faces-15000/flickr_faces_15000_original", class_mode='binary',  target_size=(128, 128), batch_size=1, shuffle =False)

Found 15002 images belonging to 1 classes.
Found 15002 images belonging to 1 classes.


In [12]:
# from tensorflow.keras.models import load_model

# # # Load the pre-trained generator model
# pretrained_generator = load_model("/kaggle/input/pretrained-generator/gen_model3000.h5", compile=True)

# # # Set the weights of the generator in your code
# generator.set_weights(pretrained_generator.get_weights())

# ## Load the pre-trained discriminator model
# pretrained_discriminator = load_model("/kaggle/input/modeloutputs/dis_e_23.h5", compile=True)

# # # Set the weights of the discriminator in your code
# discriminator.set_weights(pretrained_discriminator.get_weights())

In [13]:
batch_size = 1  
# train_lr_batches = []
# train_hr_batches = []
# for it in range(int(hr_train.shape[0] / batch_size)):
#     start_idx = it * batch_size
#     end_idx = start_idx + batch_size
#     train_hr_batches.append(hr_train[start_idx:end_idx])
#     train_lr_batches.append(lr_train[start_idx:end_idx])
    
    
epochs = 50
#iterate training over epochs
for e in range(epochs):
    
    lr_generator.reset()
    hr_generator.reset()
    
    fake_label = np.zeros((batch_size, 1)) # 0 label for all fake images
    real_label = np.ones((batch_size,1)) # 1 label for all real images.
    
     
    g_losses = []
    d_losses = []
    
    #iterate training over batches. 
    for b in tqdm(range(1000)):
        lr_imgs = lr_generator.next()[0]
        hr_imgs = hr_generator.next()[0]
        
        
        fake_imgs = generator.predict_on_batch(lr_imgs)
        
        #training the discriminator  
        discriminator.trainable = True
        d_loss_gen = discriminator.train_on_batch(fake_imgs, fake_label)
        d_loss_real = discriminator.train_on_batch(hr_imgs, real_label)
        
        #training the generator by setting the discriminator as non-trainable
        discriminator.trainable = False
        
        #Average the discriminator loss 
        d_loss = 0.5 * np.add(d_loss_gen, d_loss_real) 
        
        #Extract VGG features for content loss
        image_features = vgg.predict(hr_imgs)
     
        
        g_loss, _, _ = gan_model.train_on_batch([lr_imgs, hr_imgs], [real_label, image_features])
        
         
        d_losses.append(d_loss)
        g_losses.append(g_loss)
        
       
    g_losses = np.array(g_losses)
    d_losses = np.array(d_losses)
    
    #Calculate the average losses for generator and discriminator
    g_loss = np.sum(g_losses, axis=0) / len(g_losses)
    d_loss = np.sum(d_losses, axis=0) / len(d_losses)
    
    #Report the progress during training. 
    print("epoch:", e+1 ,"g_loss:", g_loss, "d_loss:", d_loss)

    if (e+1) % 5 == 0: 
        #Save the generator after every 5 epochs
        generator.save("gen_e_"+ str(e+1) +".h5")
        discriminator.save("dis_e_"+ str(e+1) +".h5")

  0%|          | 0/1000 [00:00<?, ?it/s]

1/1 [==============================] - 0s 165ms/step


  0%|          | 1/1000 [00:27<7:44:36, 27.90s/it]

1/1 [==============================] - 0s 18ms/step


  0%|          | 2/1000 [00:28<3:13:20, 11.62s/it]

...

1/1 [==============================] - 0s 18ms/step


100%|█████████▉| 999/1000 [03:36<00:00,  4.87it/s]

1/1 [==============================] - 0s 19ms/step


100%|██████████| 1000/1000 [03:37<00:00,  4.60it/s]

epoch: 50 g_loss: nan d_loss: [nan 0.5]


In [14]:
# generator = load_model('/kaggle/input/modeloutputs/gen_e_36.h5', compile=False)
# [X1, X2] = [lr_test, hr_test]
# ix = randint(0, len(X1), 1)
# src_image, tar_image = X1[ix], X2[ix]
# gen_image = generator.predict(src_image)
# plt.figure(figsize=(16, 8))
# plt.subplot(231)
# plt.title('LR Image')
# plt.imshow(src_image[0,:,:,:])
# plt.subplot(232)
# plt.title('Superresolution')
# plt.imshow(gen_image[0,:,:,:])
# plt.subplot(233)
# plt.title('Orig. HR image')
# plt.imshow(tar_image[0,:,:,:])
# plt.show()